# 09 — Tuning Familiar / Bridge / Adventurous by ear

Feedback from listening to notebook 08's tiers: Familiar is great, Bridge
sounds too close to Familiar, and Adventurous isn't far enough. The measured
cause of both: `tiers_for()`'s Bridge pool started scanning from rank 1 again
(so it could grab something as close as rank 2 if it merely lacked genre
overlap — no distance floor separating it from Familiar), and Adventurous used
`depth_for(0.85)` ≈ rank 197 of ~8,000 — the *2.5th percentile* of closeness,
not actually far.

## Working definitions

- **Familiar** — very similar sounding. Often the same genre, not required.
- **Bridge** — a real step further in sound than Familiar, genre may or may
  not differ. The gap from Familiar has to be audible, not just "next in line
  that happens to lack a shared genre tag."
- **Adventurous** — clearly further still — genuinely different from the
  seed, but not so far that it stops being a recognisable extension of it
  (see the catalogue's own ceiling below).

## What the catalogue's own decay curve says

Genre agreement@10-per-band and mean distance, by rank band, full 7,994-track
EffNet catalogue, ~200 seeds/band across all 8 genres:

| rank band | agreement | mean distance |
|---|---:|---:|
| 1-10 | 0.62 | 0.240 |
| 11-30 | 0.55 | 0.285 |
| 31-100 | 0.51 | 0.326 |
| 101-300 | 0.45 | 0.376 |
| 301-1000 | 0.33 | 0.448 |
| 1001-3000 | 0.16 | 0.552 |
| 3001-7993 | 0.06 | 0.695 |

Two things this settles. First, ranks 11-30 barely differ from 1-10 — that's
exactly why Bridge glued itself to Familiar before; there's no real separation
until past rank ~30. Second, by rank 3000+ agreement (0.06) falls *below* the
~0.125 random baseline for 8 balanced genres — that's not adventurous, that's
the model actively pointing at opposite-sounding music. Pushing Adventurous
past roughly rank 2000 stops being "further out" and starts being "wrong."

**Starting proposal, to test by ear, not to treat as final:**

- Familiar: rank 1-15
- Bridge: rank 30-150 (the gap from 15-30 is deliberate — a buffer so Bridge
  can't land right next to Familiar)
- Adventurous: rank 500-2000

Change the ranges in the cell below and re-run to try anything else — that's
the point of this notebook.

## Which catalogue: the 25k app catalogue, rescaled

Rounds 1–3 below were tuned by ear on fma_small's 7,994 tracks, and every
number in the intro (the decay table, the "rank ~2000" ceiling) is from that
catalogue. The app now serves fma_medium: 24,781 tracks after
`modeling/catalogue.py` removes re-uploads and silent files.

Ranks don't transfer between catalogues of different sizes: with ~3× the
tracks, rank 500 sits ~3× closer to the seed. What the ear tuned was *how
different* a tier sounds, i.e. cosine distance, so each boundary moves to the
rank where the same distance now falls (median over 300 fma_small seeds):

| fma_small rank | cosine distance | fma_medium rank |
|---:|---:|---:|
| 15 | 0.263 | 40 |
| 30 | 0.289 | 80 |
| 150 | 0.349 | 420 |
| 500 | 0.414 | 1,400 |
| 2,000 | 0.546 | 6,000 |
| 3,000 | 0.598 | 9,000 |

These are `MEDIUM_BANDS` / `MEDIUM_WIDEN_TO` in `modeling/tiers.py`, which the
app uses. Set `CATALOGUE = "small"` in the next cell to get the original
catalogue and bands back exactly.


In [1]:
import sys
sys.path.append("..")

import ast
import tempfile
import os
from pathlib import Path
import numpy as np
import pandas as pd
import essentia.standard as es
import soundfile as sf
from IPython.display import Audio, display

from modeling.data import load_fma
from modeling.effnet_recommender import EffNetRecommender
from modeling.connecting_factors import ConnectingFactors
from modeling.catalogue import load_catalogue, local_audio_path
from modeling.tiers import MEDIUM_BANDS, MEDIUM_WIDEN_TO

REPO_ROOT = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
pd.set_option("display.max_colwidth", 60)

# "medium": the app's 25k catalogue (modeling/catalogue.py: fma_medium, re-uploads and
#           silent files removed), with the bands rescaled to cover the same cosine distances.
# "small":  the 7,994-track catalogue rounds 1-3 were tuned on -- reproduces them exactly.
CATALOGUE = "medium"

if CATALOGUE == "medium":
    catalogue = load_catalogue()
    tracks = catalogue.tracks
    rec = EffNetRecommender().fit(catalogue.ids, catalogue.effnet, tracks)
    BANDS, WIDEN_ADVENTUROUS = MEDIUM_BANDS, MEDIUM_WIDEN_TO["Adventurous"]
    audio_path = local_audio_path  # 128 kbps web clip, falls back to fma_medium
else:
    from modeling.rhythm import audio_path
    tracks = load_fma("small")[1]
    rec = EffNetRecommender.from_npz(REPO_ROOT / "data" / "effnet_embeddings_full.npz", tracks)
    BANDS, WIDEN_ADVENTUROUS = {"familiar": (0, 15), "bridge": (30, 150), "adventurous": (500, 2000)}, 3000
print(f"catalogue: {CATALOGUE}, {len(rec.track_ids_)} tracks, bands {BANDS}")

genres_all = tracks[("track", "genres_all")].apply(ast.literal_eval)
genres_lookup = pd.read_csv(REPO_ROOT / "data" / "raw" / "fma_metadata" / "genres.csv", index_col=0)["title"]


def genre_names(gids):
    return [genres_lookup.get(i, str(i)) for i in gids]


def genre_sister_map(rec, tracks, k=2):
    """genre_top -> its k nearest *other* genre_top by mean-embedding cosine
    distance -- e.g. Instrumental's nearest is Experimental (dist 0.080), a
    relationship FMA's own genre tree can't express here (genres.csv's
    top_level never crosses genre_top on fma_small, so `genre_lineage` alone
    can't connect Instrumental to Experimental -- see connecting_factors.py).
    This is grounded in the same embedding space driving the recommendations,
    not a hand-curated guess."""
    emb = rec.embedding_
    genre_top = tracks.loc[emb.index, ("track", "genre_top")]
    centroids = {}
    for g in genre_top.dropna().unique():
        v = emb.loc[genre_top[genre_top == g].index].to_numpy()
        c = v.mean(axis=0)
        centroids[g] = c / np.linalg.norm(c)
    genres = list(centroids.keys())
    sisters = {}
    for g in genres:
        dists = {g2: 1 - centroids[g] @ centroids[g2] for g2 in genres if g2 != g}
        sisters[g] = set(sorted(dists, key=dists.get)[:k])
    return sisters


GENRE_CENTROIDS = genre_sister_map(rec, tracks, k=2)
cf = ConnectingFactors.build(tracks, genre_centroids=GENRE_CENTROIDS)
print("sister genres (k=2, by embedding centroid distance):")
for g, sisters in GENRE_CENTROIDS.items():
    print(f"  {g:15s} -> {sisters}")

catalogue: medium, 24781 tracks, bands {'familiar': (0, 40), 'bridge': (80, 420), 'adventurous': (1400, 6000)}


sister genres (k=2, by embedding centroid distance):
  Hip-Hop         -> {'Electronic', 'Soul-RnB'}
  Pop             -> {'Instrumental', 'Soul-RnB'}
  Rock            -> {'Blues', 'Pop'}
  Folk            -> {'Blues', 'Pop'}
  Experimental    -> {'Instrumental', 'Pop'}
  Jazz            -> {'Blues', 'International'}
  Electronic      -> {'Experimental', 'Easy Listening'}
  International   -> {'Jazz', 'Blues'}
  Soul-RnB        -> {'Blues', 'Pop'}
  Blues           -> {'Country', 'Folk'}
  Spoken          -> {'Experimental', 'Blues'}
  Country         -> {'Folk', 'Blues'}
  Classical       -> {'Instrumental', 'Jazz'}
  Old-Time / Historic -> {'Classical', 'International'}
  Instrumental    -> {'Experimental', 'Pop'}
  Easy Listening  -> {'Instrumental', 'Electronic'}


In [2]:
PREVIEW_SECONDS = 20
TARGET_RMS = 0.08
MAX_GAIN = 4.0


def load_preview(path, seconds=PREVIEW_SECONDS):
    y = es.MonoLoader(filename=str(path), sampleRate=22050)()
    sr = 22050
    skip = min(10.0, 0.1 * len(y) / sr)
    start = int(skip * sr)
    end = min(start + int(seconds * sr), len(y))
    start = max(0, end - int(seconds * sr))
    clip = y[start:end]
    rms = float(np.sqrt(np.mean(clip ** 2))) or 1e-9
    gain = min(TARGET_RMS / rms, MAX_GAIN)
    return np.clip(clip * gain, -1.0, 1.0), sr


def play(path, label_text):
    print(label_text)
    clip, sr = load_preview(path)
    with tempfile.NamedTemporaryFile(suffix=".ogg", delete=False) as f:
        sf.write(f.name, clip, sr, format="OGG", subtype="VORBIS")
        tmp_path = f.name
    try:
        display(Audio(filename=tmp_path))
    finally:
        os.unlink(tmp_path)

## The tunable tier tool

`explore_tiers` takes explicit **rank ranges** for each tier — not "first N
that pass some filter" — so tiers are structurally separated by distance no
matter what connects them. Within a gated tier's rank range, it *prefers*
candidates connected by at least one factor from that tier's own allowed set
— falling back to the plain distance-ranked pool if fewer than `n` connected
candidates exist in that band, so a tight range never comes up empty.

Each tier gets its **own** allowed-factor set now, not one shared list —
`gate_factors={"Bridge": ("era",), "Adventurous": None}` (`None` = any of the
five, `related_genre` included — see below). Current reasoning: genre is
excluded from Bridge's gate entirely — a Bridge pick sharing the seed's own
genre tag isn't really bridging anywhere. Geography is excluded too,
deliberately, not because it doesn't matter but because *requiring* a country
match would stop Bridge from ever connecting two very different countries —
the opposite of what it's for. Era stays as the one required anchor for now
(and as of the previous patch, `era` now falls back to `album.date_created`
when `date_released` is missing, so it's available for 100% of tracks instead
of 67% — no more seeds where Bridge's gate is silently unsatisfiable).
`factors_between` still reports every factor that actually applies to a pick
(shown in full below), even ones not used to gate it — so a Bridge pick can
show `via ['genre', 'era']` when genre happened to match too; only `era`
decided whether it qualified.

**A fifth connecting factor: `related_genre`.** FMA's own genre tree
(`genre_lineage`) can't express "Instrumental is close to Experimental" on
fma_small — its `top_level` partition never crosses `genre_top` here (see
`connecting_factors.py`'s docstring). So `related_genre` is grounded in the
embedding space instead: mean per-`genre_top` centroid, cosine distance,
each genre's `k` nearest *other* centroids (`GENRE_CENTROIDS`, computed in
the setup cell, `k=2` by default). Concretely: Instrumental's nearest is
Experimental (0.080), then Pop (0.099) — which is exactly the "obvious
bridge" already showing up by ear. `related_genre` fires when either track's
`genre_top` is in the other's sister set.

**Two diversity caps, not one.** `max_same_genre_share` (existing) caps how
much of a tier may share the seed's exact `genre_top`. `max_sister_genre_share`
(new) caps how much may land in that *sister* set instead — this is the direct
answer to "Bridge sounds good but obvious": capping same-genre alone still let
the audibly-closest *other* genre (Experimental, for an Instrumental seed)
quietly fill the rest of the tier. Capping both pushes the remainder into a
**third, genuinely distant bucket** — connected only by whatever the tier's
gate requires (era, by default), not by genre proximity at all. `0.0` = never;
`None` = uncapped; today's defaults: `max_same_genre_share={"Bridge": 0.25,
"Adventurous": 0.2}`, `max_sister_genre_share={"Bridge": 0.4, "Adventurous":
0.2}`.

Same-genre and sister-genre picks only ever come from the tier's own rank
band. Only the **distant** bucket widens past it (`widen_to`, past the tier's
own band, not into the next tier's territory) when the band runs short — same
policy as before, just applied to a third bucket instead of a second. Any
shortfall after widening backfills sister first, then same, as a last resort.

**Two more knobs, both new, both `Adventurous`-only for now:**

- `exclude_same_decade` — tier labels whose candidate pool is pre-filtered to
  a different decade than the seed (`floor(year/10)` differs; unknown years on
  either side pass through, since a missing year can't prove sameness). This
  runs *before* the gate and the genre caps, so it shrinks the pool those see.
- `prefer_different_country` — tier labels where same-country candidates are
  pushed to the back of the pick order, not excluded — a soft preference, since
  geography coverage is only ~67% and a hard requirement would starve seeds
  whose own country is common in the catalogue (most of it is US-heavy).

Note the genre-diversity cap and `related_genre` use **different** notions of
"related": the cap only checks the *seed's own* top-`k` sisters (so it can be
tuned to squeeze that specific tier), while `related_genre` as reported by
`factors_between` is symmetric (either direction counts). A pick can land in
the "distant" bucket for capping purposes and still legitimately show `via
['related_genre']` if it's a sister of the seed's genre from the *other*
side — that's not a bug, the two mechanisms answer different questions
(how to divide up the picks vs. what actually explains one).

In [3]:
ALL_FACTORS = ("genre", "genre_lineage", "related_genre", "era", "geography")


def _genre_top(track_id):
    return tracks.loc[track_id, ("track", "genre_top")]


def _different_decade(seed_id, candidate_id):
    """True unless both years are known AND fall in the same decade -- an
    unknown year can't be proven same-decade, so it passes rather than being
    penalized (same policy as every other factor here: missing data is
    skipped, never counted as a mismatch)."""
    ys, yc = cf.year.get(seed_id), cf.year.get(candidate_id)
    if pd.isna(ys) or pd.isna(yc):
        return True
    return int(ys) // 10 != int(yc) // 10


def _cap_genre_diversity(pool_idx, candidate_ids, seed_id, seed_genre, n,
                          max_same_share, max_sister_share, allowed_set, rng,
                          widen_to=None, prefer_different_country=False, seed_country=None):
    """Split pool_idx into same-genre / sister-genre (GENRE_CENTROIDS,
    computed in the setup cell) / distant-genre buckets relative to
    seed_genre. Same- and sister-genre picks only ever come from pool_idx
    itself, each capped at floor(n * its max_share) -- None means uncapped.
    Distant-genre picks come from pool_idx first; if that's not enough,
    search further out in rank (up to widen_to, exclusive) for more,
    applying the same allowed_set connection gate to anything found there.
    Any shortfall backfills from sister first, then same, as a last resort --
    sister is still "connected", same is the least interesting fallback.

    When prefer_different_country is set, within the sister/distant buckets
    candidates whose resolved country matches seed_country are pushed behind
    ones that differ or are unknown -- a soft preference (reordering, not a
    cut), since geography coverage is only ~67% and a hard requirement would
    starve tightly-clustered seeds."""
    pool_idx = list(pool_idx)
    if seed_genre is None or not pool_idx:
        # no genre to compare against (the external seed has none) -- fall
        # back to a plain n-sized sample, NOT the whole unfiltered band
        return list(rng.choice(pool_idx, size=min(n, len(pool_idx)), replace=False)) if pool_idx else []

    sister_genres = GENRE_CENTROIDS.get(seed_genre, set())

    def bucket(i):
        g = _genre_top(candidate_ids[i])
        if g == seed_genre:
            return "same"
        return "sister" if g in sister_genres else "distant"

    def deprioritize_same_country(idxs):
        if not prefer_different_country or seed_country is None or pd.isna(seed_country):
            return idxs
        different, same_country = [], []
        for i in idxs:
            c = cf.country.get(candidate_ids[i])
            (same_country if c == seed_country else different).append(i)
        return different + same_country

    same_idx = [i for i in pool_idx if bucket(i) == "same"]
    sister_idx = [i for i in pool_idx if bucket(i) == "sister"]
    distant_idx = [i for i in pool_idx if bucket(i) == "distant"]

    max_same = int(np.floor(n * max_same_share)) if max_same_share is not None else n
    max_sister = int(np.floor(n * max_sister_share)) if max_sister_share is not None else n
    n_same = min(max_same, len(same_idx))
    n_sister = min(max_sister, len(sister_idx))
    needed_distant = n - n_same - n_sister

    if len(distant_idx) < needed_distant and widen_to is not None and pool_idx and widen_to > pool_idx[-1]:
        for j in range(pool_idx[-1] + 1, widen_to):
            if len(distant_idx) >= needed_distant:
                break
            if _genre_top(candidate_ids[j]) in ({seed_genre} | sister_genres):
                continue
            if allowed_set is not None and seed_id is not None:
                if not (set(cf.factors_between(seed_id, candidate_ids[j])) & allowed_set):
                    continue
            distant_idx.append(j)  # appended in rank order (closest-first), since j increases

    n_distant = min(needed_distant, len(distant_idx))
    shortfall = n - (n_same + n_sister + n_distant)
    if shortfall > 0:  # backfill: sister first (still "connected"), then same, as a last resort
        extra = min(shortfall, len(sister_idx) - n_sister)
        n_sister += extra
        shortfall -= extra
    if shortfall > 0:
        n_same = min(len(same_idx), n_same + shortfall)

    same_pick = list(rng.choice(same_idx, size=n_same, replace=False)) if n_same else []
    sister_pick = deprioritize_same_country(sister_idx)[:n_sister]
    distant_pick = deprioritize_same_country(distant_idx)[:n_distant]
    chosen = same_pick + sister_pick + distant_pick
    return chosen if chosen else pool_idx[: min(n, len(pool_idx))]


def explore_tiers(seed_id=None, seed_vec=None, seed_artist=None,
                   familiar=BANDS["familiar"], bridge=BANDS["bridge"], adventurous=BANDS["adventurous"], n=5,
                   gate_factors=None, max_same_genre_share=None, max_sister_genre_share=None,
                   widen_to=None, exclude_same_decade=None, prefer_different_country=None, seed=0):
    gate_factors = gate_factors or {"Bridge": ("era",), "Adventurous": None}
    # 0.0 = never the seed's own genre_top; 0.25 = up to ~1/4 of picks may;
    # None = no cap. max_sister_genre_share works the same way but against
    # GENRE_CENTROIDS' sister set (e.g. Experimental for an Instrumental
    # seed) -- capping it pushes picks toward genuinely distant genres
    # instead of the audibly-closest-but-still-obvious neighbour.
    max_same_genre_share = {"Bridge": 0.25} if max_same_genre_share is None else max_same_genre_share
    max_sister_genre_share = {} if max_sister_genre_share is None else max_sister_genre_share
    # how far out (exclusive upper rank bound) a tier may search for
    # distant-genre candidates once its own band runs short
    widen_to = {"Bridge": adventurous[0]} if widen_to is None else widen_to
    # tier labels for which the candidate pool is pre-filtered to a different
    # decade than the seed (unknown years pass through -- see _different_decade)
    exclude_same_decade = set() if exclude_same_decade is None else set(exclude_same_decade)
    # tier labels for which same-country candidates are pushed to the back of
    # the pick order rather than excluded (soft preference, ~67% coverage)
    prefer_different_country = set() if prefer_different_country is None else set(prefer_different_country)

    if seed_vec is None:
        row = rec._position(seed_id)
        seed_vec = rec.embedding_.iloc[[row]]
    widen_values = [v for v in widen_to.values() if v is not None]
    search_n = max(adventurous[1] + 1, (max(widen_values) + 1) if widen_values else 0, 50)
    distances, idx = rec.index_.kneighbors(seed_vec, n_neighbors=search_n)
    distances, idx = distances[0], idx[0]
    if seed_id is not None:
        distances, idx = distances[1:], idx[1:]
    candidate_ids = rec.track_ids_[idx]

    if seed_artist is not None:
        artists = tracks.loc[candidate_ids, ("artist", "name")].to_numpy()
        keep = artists != seed_artist
        candidate_ids, distances = candidate_ids[keep], distances[keep]

    seed_genre = _genre_top(seed_id) if seed_id is not None else None
    seed_country = cf.country.get(seed_id) if seed_id is not None else None

    rng = np.random.default_rng(seed)
    out = {}
    for label, (lo, hi) in [("Familiar", familiar), ("Bridge", bridge), ("Adventurous", adventurous)]:
        hi = min(hi, len(candidate_ids))
        pool_idx = np.arange(lo, hi)

        if label in exclude_same_decade and seed_id is not None and len(pool_idx):
            pool_idx = np.array([i for i in pool_idx if _different_decade(seed_id, candidate_ids[i])])

        allowed = gate_factors.get(label) if label in gate_factors else "skip"
        allowed_set = set(allowed or ALL_FACTORS) if allowed != "skip" else None
        if allowed_set is not None and seed_id is not None and len(pool_idx):
            connected = [i for i in pool_idx if set(cf.factors_between(seed_id, candidate_ids[i])) & allowed_set]
            pool_for_pick = connected if len(connected) >= n else list(pool_idx)
        else:
            pool_for_pick = list(pool_idx)

        same_share = max_same_genre_share.get(label) if label in max_same_genre_share else None
        sister_share = max_sister_genre_share.get(label) if label in max_sister_genre_share else None
        if same_share is not None or sister_share is not None:
            pick = _cap_genre_diversity(pool_for_pick, candidate_ids, seed_id, seed_genre, n,
                                         same_share, sister_share, allowed_set, rng,
                                         widen_to=widen_to.get(label),
                                         prefer_different_country=label in prefer_different_country,
                                         seed_country=seed_country)
        else:
            pick = list(rng.choice(pool_for_pick, size=min(n, len(pool_for_pick)), replace=False)) if pool_for_pick else []
        pick = sorted(pick)
        factors = [cf.factors_between(seed_id, candidate_ids[i]) if seed_id is not None else [] for i in pick]
        out[label] = [(candidate_ids[i], distances[i], i + 1, f) for i, f in zip(pick, factors)]
    return out


def show_and_play(seed_path, seed_label, tiers):
    play(seed_path, seed_label)
    for label, items in tiers.items():
        for tid, d, rank, factors in items:
            m = tracks.loc[tid]
            g = genre_names(genres_all.get(tid, []))
            factor_tag = f" via {factors}" if factors else " (no connecting factor -- fallback)"
            play(audio_path(tid),
                 f"{label}  rank={rank}  distance={d:.3f}{factor_tag}  {m[('artist','name')]} — {m[('track','title')]}  "
                 f"[{m[('track','genre_top')]}] {cf.describe(tid)}")

### Round 1: the starting proposal, on the same three catalogue seeds as
notebooks 07/08 — Hip-Hop (coherent), Instrumental (best genre-agreement),
Pop (the incoherent one) — plus the external seed.

One limitation, not a bug: the external seed has no `genres_all`/era/country
of its own (it never went through FMA's metadata pipeline), so connecting
factors can't be computed for it — its Bridge/Adventurous picks fall back to
pure distance ranking every time, tagged "(no connecting factor -- fallback)"
below. That's expected for this seed specifically, not a sign the tool is
broken.

In [4]:
ROUND_SEEDS = [2, 40659, 3538]  # AWOL - Food; Albert Glasser - The Auction 2; Cryptacize - Say You Will

for seed_id in ROUND_SEEDS:
    m = tracks.loc[seed_id]
    tiers = explore_tiers(seed_id=seed_id, seed_artist=m[("artist", "name")])
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}] ===")
    show_and_play(audio_path(seed_id), "SEED", tiers)


=== SEED 2  AWOL — Food  [Hip-Hop] ===
SEED


Familiar  rank=11  distance=0.184 via ['genre', 'era', 'geography']  K. Sparks — Blue Nostalgia  [Hip-Hop] 2010, United States


Familiar  rank=13  distance=0.189 via ['genre', 'geography']  Hi-Rez — Throw It Up Ft. BDG (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=20  distance=0.195 via ['genre', 'era']  Sleaze — Is That Enough?  [Hip-Hop] 2010


Familiar  rank=24  distance=0.204 via ['genre', 'era', 'geography']  K. Sparks — Success  [Hip-Hop] 2011, United States


...

Adventurous  rank=3692  distance=0.396 via ['related_genre']  Blue Dot Sessions — Ballast  [Instrumental] 2015


Adventurous  rank=4173  distance=0.405 via ['related_genre']  Chris Forsyth — The First Ten Minutes of Cocksucker Blues  [Folk] 2012


Adventurous  rank=4360  distance=0.409 via ['era', 'geography']  Here's How — You Showed Me The Way  [Jazz] 2006, United States


Adventurous  rank=5583  distance=0.430 via ['related_genre']  Death By Unga Bunga — Tell Me Why  [Rock] 2016, Norway


Adventurous  rank=5856  distance=0.435 via ['related_genre']  Sister Slacks — Clockwork  [Rock] 2012, France


In [5]:
SEED_PATH = REPO_ROOT / "data" / "raw" / "youtube_tests" / "Y2Mate.is - Elyjah Slaps the Space.mp3"

external = np.load(REPO_ROOT / "data" / "processed" / "essentia_handoff" / "external_effnet_embeddings.npz",
                    allow_pickle=True)
ext_names, ext_platforms, ext_vecs = external["names"], external["platforms"], external["embeddings"]
ext_vecs_u = ext_vecs / np.linalg.norm(ext_vecs, axis=1, keepdims=True)
seed_idx = int(np.flatnonzero(ext_platforms == "seed")[0])
seed_vec_2d = ext_vecs_u[seed_idx].reshape(1, -1)

tiers = explore_tiers(seed_vec=seed_vec_2d)
print("=== SEED — Elyjah Slaps the Space (external) ===")
show_and_play(SEED_PATH, "SEED", tiers)

=== SEED — Elyjah Slaps the Space (external) ===
SEED


Familiar  rank=11  distance=0.220 (no connecting factor -- fallback)  6th Sense — 4AM Instrumental     {Wildabeast}  [Hip-Hop] 2009


Familiar  rank=13  distance=0.227 (no connecting factor -- fallback)  Blue Ducks — Floss Suffers From Gamma Radiation  [Hip-Hop] 2011


Familiar  rank=20  distance=0.248 (no connecting factor -- fallback)  Kriss — Jazz Club  [Jazz] 2009


Familiar  rank=24  distance=0.259 (no connecting factor -- fallback)  Deltason — Tunnel Vision  [Electronic] 2012


...

Adventurous  rank=2676  distance=0.490 (no connecting factor -- fallback)  Marlaja Virta & ono — Dick Laurent is dead  [Electronic] 2014


Adventurous  rank=3974  distance=0.525 (no connecting factor -- fallback)  K.I.R.K — Gettin' Crazy  [Hip-Hop] 2016, United States


Adventurous  rank=4487  distance=0.536 (no connecting factor -- fallback)  The Polish Ambassador — Space Camp Goodbyes  [Electronic] 2008


Adventurous  rank=5153  distance=0.550 (no connecting factor -- fallback)  eden — DANDY  [Electronic] 2014


Adventurous  rank=5699  distance=0.562 (no connecting factor -- fallback)  The Polish Ambassador — Banana Bread Break  [Electronic] 2006


### Round 2 — change the numbers here and re-run

Nudge `familiar` / `bridge` / `adventurous` (the `(low_rank, high_rank)` rank
bands), `gate_factors` (which connecting factors are required per tier —
`None` means any of the five), `max_same_genre_share` / `max_sister_genre_share`
(how much of a tier may share the seed's exact genre, or its sister genre,
applied after the gate), `widen_to` (how far a tier may search for distant-genre
candidates once its own band runs short), `exclude_same_decade` (tier labels
that must differ from the seed's decade), and `prefer_different_country` (tier
labels that push same-country picks to the back) based on what round 1 sounded
like, then re-run this cell. Repeat until the three tiers feel right; whatever
lands here is what should go into the actual product code.

Current setting: Bridge requires **era only**, is capped at **25% same-genre**
and **40% sister-genre** (so at least 1 of 5 comes from a genuinely distant
genre once the band supports it), and widens its distant-genre search up to
where Adventurous starts if its own band comes up short. Adventurous is capped
at **20% same-genre** and **20% sister-genre** (3 of 5 pushed toward distant
genres), excludes the seed's own **decade**, prefers a **different country**
when known, and widens its distant-genre search out to rank 3000 — still
inside the catalogue's own "recognisable extension" ceiling from the intro
(agreement falls below the random baseline past ~3000).

In [6]:
familiar = BANDS["familiar"]        # small: (0, 15)    medium: (0, 40)
bridge = BANDS["bridge"]            # small: (30, 150)  medium: (80, 420)
adventurous = BANDS["adventurous"]  # small: (500, 2000) medium: (1400, 6000)
gate_factors = {"Bridge": ("era",), "Adventurous": None}
max_same_genre_share = {"Bridge": 0.25, "Adventurous": 0.2}
max_sister_genre_share = {"Bridge": 0.4, "Adventurous": 0.2}
widen_to = {"Bridge": adventurous[0], "Adventurous": WIDEN_ADVENTUROUS}  # small: 3000, medium: 9000
exclude_same_decade = {"Adventurous"}
prefer_different_country = {"Adventurous"}

for seed_id in ROUND_SEEDS:
    m = tracks.loc[seed_id]
    tiers = explore_tiers(seed_id=seed_id, seed_artist=m[("artist", "name")],
                           familiar=familiar, bridge=bridge, adventurous=adventurous,
                           gate_factors=gate_factors, max_same_genre_share=max_same_genre_share,
                           max_sister_genre_share=max_sister_genre_share, widen_to=widen_to,
                           exclude_same_decade=exclude_same_decade,
                           prefer_different_country=prefer_different_country)
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}] ===")
    show_and_play(audio_path(seed_id), "SEED", tiers)

tiers = explore_tiers(seed_vec=seed_vec_2d, familiar=familiar, bridge=bridge, adventurous=adventurous,
                       gate_factors=gate_factors, max_same_genre_share=max_same_genre_share,
                       max_sister_genre_share=max_sister_genre_share, widen_to=widen_to,
                       exclude_same_decade=exclude_same_decade, prefer_different_country=prefer_different_country)
print("\n=== SEED — Elyjah Slaps the Space (external) ===")
show_and_play(SEED_PATH, "SEED", tiers)


=== SEED 2  AWOL — Food  [Hip-Hop] ===
SEED


Familiar  rank=11  distance=0.184 via ['genre', 'era', 'geography']  K. Sparks — Blue Nostalgia  [Hip-Hop] 2010, United States


Familiar  rank=13  distance=0.189 via ['genre', 'geography']  Hi-Rez — Throw It Up Ft. BDG (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=20  distance=0.195 via ['genre', 'era']  Sleaze — Is That Enough?  [Hip-Hop] 2010


Familiar  rank=24  distance=0.204 via ['genre', 'era', 'geography']  K. Sparks — Success  [Hip-Hop] 2011, United States


...

Adventurous  rank=2676  distance=0.490 (no connecting factor -- fallback)  Marlaja Virta & ono — Dick Laurent is dead  [Electronic] 2014


Adventurous  rank=3974  distance=0.525 (no connecting factor -- fallback)  K.I.R.K — Gettin' Crazy  [Hip-Hop] 2016, United States


Adventurous  rank=4487  distance=0.536 (no connecting factor -- fallback)  The Polish Ambassador — Space Camp Goodbyes  [Electronic] 2008


Adventurous  rank=5153  distance=0.550 (no connecting factor -- fallback)  eden — DANDY  [Electronic] 2014


Adventurous  rank=5699  distance=0.562 (no connecting factor -- fallback)  The Polish Ambassador — Banana Bread Break  [Electronic] 2006


### Aside: could EchoNest or the MFCC+rhythm (`heard`) features shape Bridge/Adventurous?

Asked while tuning this — answering here since it explains why neither is
wired into `ConnectingFactors` alongside genre/era/geography/related_genre.

**EchoNest** (`data/raw/fma_metadata/echonest.csv`, explored in notebook 07):
acousticness/danceability/energy/instrumentalness/liveness/speechiness/tempo/
valence — the same feature family behind Spotify's `audio-features` API.
Two problems for this job specifically: **coverage** is 1,294/8,000 tracks
(16%) — most seeds would have nothing to compare against, unlike era/geography
which are ~67-100%. And where it *does* exist, the correlation with EffNet
heard-space distance is weak-but-real (r≈0.26) — strongest on
acousticness/energy/danceability (timbre/rhythm-adjacent, expected), close to
blind on valence/liveness/tempo. It's a legitimate independent signal, but too
sparse to gate a whole tier on. If it's ever wanted as an *optional* sixth
factor (fires only on the 16% that have it, same pattern as `related_genre`
firing only when `GENRE_CENTROIDS` says so), that's a small addition — not
proposed here since neither tier's gate is short on connected candidates right
now.

**MFCC + rhythm + HPSS (`heard` space)**: per `FOR_TIM.md`, this is a
*different, separate* recommender — `feature/pca-recommendation` branch,
StandardScaler → PCA → NearestNeighbors on 154 hand-picked columns (140 MFCC
+ 13 rhythm + 1 drum/instrument energy ratio) — not part of this EffNet
pipeline, and its embedding space isn't the one `rec` here is built on, so its
distances aren't directly comparable to the ranks this notebook uses.
Genuinely validated, though, and worth knowing: it beat the full 518-column
space and a 238-column variant on correlation with the 80-pair human
listening test (r=-0.358 vs. +0.05 and -0.213). Two pieces of it *are* present
as plain CSVs in this branch already
(`data/rhythm_features.csv`/`_medium.csv`, `data/separation_features.csv`/
`_medium.csv`) if a rhythm- or timbre-based connecting factor is ever wanted —
but raw tempo specifically was already measured and rejected as a factor (see
`connecting_factors.py`'s docstring: eta²=0.019 against genre, undermined by
octave-ambiguity). Onset rate/strength/pulse-clarity or the HPSS ratio weren't
individually re-tested for that purpose; they'd need the same kind of check
before being trusted as an explanation a listener could point to, the same bar
every other factor here was held to.

**Bottom line for today's tuning:** neither is a quick win for Bridge/
Adventurous specifically — EchoNest on coverage, `heard` on being a different
embedding entirely. `related_genre` (embedding-centroid based, same space as
everything else in this notebook) covers the actual gap that came up: FMA's
own genre tree can't express "Instrumental is close to Experimental" on
fma_small.